# Exemplo de ETL

## Objetivo
- Usando o exemplo simples de ETL, mostrar as funções
  - Criação do Cluster Apache Spark
  - Navegação `Markdown`
  - Sistema de arquivos `workspace`
  - Catalog
  - Histórico de alterações
  - Depuração de variáveis
  - Spark UI

## O que é ETL?

**ETL** é uma sigla que significa **Extract, Transform, Load** (Extração, Transformação e Carga).

![ETL](https://raw.githubusercontent.com/rafael-negrao/laboratorio-databricks/main/imagens/etl.png)

- **Extract (Extração):** Consiste em capturar dados de diversas fontes, como bancos de dados, APIs, arquivos e sistemas legados.

- **Transform (Transformação):** Os dados extraídos são processados e transformados para garantir qualidade, consistência e formato adequado para análise. Isso pode incluir limpeza, agregação, normalização e outras transformações.

- **Load (Carga):** Os dados transformados são carregados em um sistema de destino, como um data warehouse, onde podem ser analisados e utilizados para gerar insights.

## Criação do cluster

Documentação de referência: https://docs.databricks.com/pt/compute/index.html

Como mostrar a sessão do spark

In [0]:
spark

## Extract

Puxando os dados do github

In [0]:
%sh
wget -O /tmp/covid_data.csv https://raw.githubusercontent.com/owid/covid-19-data/master/public/data/owid-covid-data.csv

--2024-08-26 23:58:00--  https://raw.githubusercontent.com/owid/covid-19-data/master/public/data/owid-covid-data.csv
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.111.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 98391483 (94M) [text/plain]
Saving to: ‘/tmp/covid_data.csv’

     0K .......... .......... .......... .......... ..........  0% 24.2M 4s
    50K .......... .......... .......... .......... ..........  0% 23.2M 4s
   100K .......... .......... .......... .......... ..........  0% 22.8M 4s
   150K .......... .......... .......... .......... ..........  0% 44.2M 4s
   200K .......... .......... .......... .......... ..........  0% 20.9M 4s
   250K .......... .......... .......... .......... ..........  0%  160M 3s
   300K .......... .......... .......... .......... ..........  0% 35.1M 3s
   350K .

In [0]:
dbutils.fs.mv("file:/tmp/covid_data.csv", "dbfs:/tmp/covid_data.csv")

True

In [0]:
display(dbutils.fs.ls("dbfs:/tmp/"))

path,name,size,modificationTime
dbfs:/tmp/covid_data.csv,covid_data.csv,98391483,1724716682000


In [0]:
file = "dbfs:/tmp/covid_data.csv"
df = spark.read.csv(file, header=True, inferSchema=True)

Criar o database para recepcionar os dados

In [0]:
%sql
create database if not exists covid_db;

- Exibindo os dados 
- Análise exploratória (data profile)

In [0]:
display(df)

iso_code,continent,location,date,total_cases,new_cases,new_cases_smoothed,total_deaths,new_deaths,new_deaths_smoothed,total_cases_per_million,new_cases_per_million,new_cases_smoothed_per_million,total_deaths_per_million,new_deaths_per_million,new_deaths_smoothed_per_million,reproduction_rate,icu_patients,icu_patients_per_million,hosp_patients,hosp_patients_per_million,weekly_icu_admissions,weekly_icu_admissions_per_million,weekly_hosp_admissions,weekly_hosp_admissions_per_million,total_tests,new_tests,total_tests_per_thousand,new_tests_per_thousand,new_tests_smoothed,new_tests_smoothed_per_thousand,positive_rate,tests_per_case,tests_units,total_vaccinations,people_vaccinated,people_fully_vaccinated,total_boosters,new_vaccinations,new_vaccinations_smoothed,total_vaccinations_per_hundred,people_vaccinated_per_hundred,people_fully_vaccinated_per_hundred,total_boosters_per_hundred,new_vaccinations_smoothed_per_million,new_people_vaccinated_smoothed,new_people_vaccinated_smoothed_per_hundred,stringency_index,population_density,median_age,aged_65_older,aged_70_older,gdp_per_capita,extreme_poverty,cardiovasc_death_rate,diabetes_prevalence,female_smokers,male_smokers,handwashing_facilities,hospital_beds_per_thousand,life_expectancy,human_development_index,population,excess_mortality_cumulative_absolute,excess_mortality_cumulative,excess_mortality,excess_mortality_cumulative_per_million
AFG,Asia,Afghanistan,2020-01-05,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-06,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-07,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-08,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-09,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-10,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-11,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-12,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,nul

Databricks data profile. Run in Databricks to view.

In [0]:
(
  df
    .write
    .mode(saveMode="overwrite")
    .saveAsTable("covid_db.covid_data")
)

## Transform

In [0]:
df_covid = spark.read.table("covid_db.covid_data")

In [0]:
display(
    spark.sql("DESCRIBE DETAIL covid_db.covid_data")
)

format,id,name,description,location,createdAt,lastModified,partitionColumns,clusteringColumns,numFiles,sizeInBytes,properties,minReaderVersion,minWriterVersion,tableFeatures,statistics
delta,f0441aef-7624-4613-9f79-9ecabdde4f82,spark_catalog.covid_db.covid_data,null,dbfs:/user/hive/warehouse/covid_db.db/covid_data,2024-08-26T23:53:22.35Z,2024-08-26T23:58:22Z,List(),List(),8,12587758,Map(delta.enableDeletionVectors -> true),3,7,List(deletionVectors),"Map(numRowsDeletedByDeletionVectors -> 0, numDeletionVectors -> 0)"


In [0]:
display(df_covid)

iso_code,continent,location,date,total_cases,new_cases,new_cases_smoothed,total_deaths,new_deaths,new_deaths_smoothed,total_cases_per_million,new_cases_per_million,new_cases_smoothed_per_million,total_deaths_per_million,new_deaths_per_million,new_deaths_smoothed_per_million,reproduction_rate,icu_patients,icu_patients_per_million,hosp_patients,hosp_patients_per_million,weekly_icu_admissions,weekly_icu_admissions_per_million,weekly_hosp_admissions,weekly_hosp_admissions_per_million,total_tests,new_tests,total_tests_per_thousand,new_tests_per_thousand,new_tests_smoothed,new_tests_smoothed_per_thousand,positive_rate,tests_per_case,tests_units,total_vaccinations,people_vaccinated,people_fully_vaccinated,total_boosters,new_vaccinations,new_vaccinations_smoothed,total_vaccinations_per_hundred,people_vaccinated_per_hundred,people_fully_vaccinated_per_hundred,total_boosters_per_hundred,new_vaccinations_smoothed_per_million,new_people_vaccinated_smoothed,new_people_vaccinated_smoothed_per_hundred,stringency_index,population_density,median_age,aged_65_older,aged_70_older,gdp_per_capita,extreme_poverty,cardiovasc_death_rate,diabetes_prevalence,female_smokers,male_smokers,handwashing_facilities,hospital_beds_per_thousand,life_expectancy,human_development_index,population,excess_mortality_cumulative_absolute,excess_mortality_cumulative,excess_mortality,excess_mortality_cumulative_per_million
AFG,Asia,Afghanistan,2020-01-05,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-06,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-07,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-08,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-09,0,0,null,0,0,null,0.0,0.0,null,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-10,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-11,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,0.0,54.42,18.6,2.58,1.34,1803.99,null,597.03,9.59,null,null,37.75,0.5,64.83,0.51,41128772,null,null,null,null
AFG,Asia,Afghanistan,2020-01-12,0,0,0.0,0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,null,nul

In [0]:
df_covid.createOrReplaceTempView("covid_data")

In [0]:
%sql
select location, `date`, total_cases, new_cases, total_deaths
  from covid_db.covid_data

location,date,total_cases,new_cases,total_deaths
Afghanistan,2020-01-05,0,0,0
Afghanistan,2020-01-06,0,0,0
Afghanistan,2020-01-07,0,0,0
Afghanistan,2020-01-08,0,0,0
Afghanistan,2020-01-09,0,0,0
Afghanistan,2020-01-10,0,0,0
Afghanistan,2020-01-11,0,0,0
Afghanistan,2020-01-12,0,0,0
Afghanistan,2020-01-13,0,0,0
Afghanistan,2020-01-14,0,0,0


In [0]:
df_selected = df.select("location", "date", "total_cases", "new_cases", "total_deaths")

# outra forma de fazer a mesma coisa
df_selected = spark.sql(
"""
select location, `date`, total_cases, new_cases, total_deaths
  from covid_db.covid_data
""")

In [0]:
import pyspark.sql.functions as f

df_selected = df_selected.where(f.col("location") == "United States")

In [0]:
df_transformed = (
    df_selected.withColumn("case_fatality_rate", f.col("total_deaths") / f.col("total_cases"))
)

## Load

In [0]:

(
    df_transformed
    .write
    .mode(saveMode="overwrite")
    .format("delta")
    .saveAsTable("covid_db.covid_transformed")
)